# Gemelo digital de la mano — entrenamiento completo

**Prótesis mioeléctrica con reconocimiento de gestos por IA** · Roldán Rodríguez — Ing. CCIA

Un solo notebook, en orden. **"Ejecutar todo"** corre el proceso completo; lo que ya existe en disco (datasets, modelos) se reutiliza, salvo que actives su interruptor en la sección 0.

| # | Sección | Qué produce |
|---|---|---|
| 0 | Configuración y entorno | interruptores, verificación de la GPU |
| 1 | **D1** EMG sintético (dos vistas físicas) | ~80.640 ventanas de 200 ms × 2 canales |
| 2 | **D2** poses de mano sintéticas | 60.000 poses de 21 puntos (topología MediaPipe) |
| 3 | **D3** poses reales con webcam | lo que captures con `capturar_poses.py` |
| 4 | **D4** EMG real público (UCI) | ~71.000 ventanas de 36 personas reales |
| 5 | Línea base: la red actual 8-32-16-7 | punto de comparación |
| 6 | **Aprendizaje contrastivo en vivo** (SimCLR → SupCon) | codificador profesor |
| 7 | Espacio latente: formas descubiertas (no supervisado) | grupos, completitud |
| 8 | Cabezas multitarea: gesto + pose + fuerza | R² de pose y fuerza |
| 9 | Red de formas de la mano (D2/D3) | espacio de formas 3D, R² |
| 10 | Estudiante para el ESP32 (destilación) | `modelo_red.h` |
| 11 | Refuerzo de los servos | `poses_aprendidas.h`, R² de pose |
| 12 | Exportación y resumen de R² | `.h5`, `.keras`, ficha del modelo |

**Kernel:** *Gemelo Mano (Python 3.12 · GPU)* — Keras 3 sobre PyTorch con CUDA (RTX 4050).
**Regla del proyecto:** todo modelo reporta un R² (real en regresión; pseudo-R² de McFadden en clasificación).

## 0. Configuración

In [1]:
# ====== Interruptores ======  (si el archivo no existe, se genera/entrena aunque esté en False)
REGENERAR_D1 = False            # EMG sintético
REGENERAR_D2 = False            # poses sintéticas
REGENERAR_D4 = False            # UCI (descarga 17 MB la primera vez)
REENTRENAR_BASE = False         # red actual 8-32-16-7 sobre D1
REENTRENAR_CONTRASTIVO = False
REENTRENAR_CABEZAS = False
REENTRENAR_FORMAS = False
REENTRENAR_ESTUDIANTE = False
REENTRENAR_REFUERZO = False
REENTRENAR_TODO = False         # True = reentrena todos los modelos (para ver el aprendizaje completo en vivo)

# ====== Tamaños y entrenamiento ======
N_PERSONAS_D1 = 160             # × 3 rondas × 7 gestos × 24 ventanas ≈ 80.640 ventanas
N_POSES_D2 = 60_000
EPOCAS_SIMCLR = 15              # fase NO supervisada
EPOCAS_SUPCON = 15              # fase supervisada
LOTE = 512
USAR_UCI_EN_CONTRASTIVO = True  # mezcla EMG real (sin y con etiqueta) en el contrastivo
ITERACIONES_REFUERZO = 800
VER_EN_VIVO = True
ABRIR_TABLERO = True            # abre en el navegador el tablero en vivo (http://127.0.0.1:8765)
USAR_GPU = True                 # en un portátil, entrena con el cargador conectado: en batería Windows puede apagar la GPU
SEMILLA = 42

In [2]:
import os, sys, json, pickle, time, logging, warnings, subprocess
os.environ["KERAS_BACKEND"] = "torch"
if not USAR_GPU:
    os.environ["CUDA_VISIBLE_DEVICES"] = ""      # todo en la CPU (más lento, mismos resultados)
elif sys.platform == "win32":                    # ¿la GPU responde? (en batería puede estar apagada)
    try:
        subprocess.run([sys.executable, "-c", "import torch; torch.ones(1, device='cuda').cpu()"],
                       timeout=60, check=True, capture_output=True)
    except Exception:
        raise RuntimeError("La GPU no responde. Conecta el cargador (en batería Windows la apaga) "
                           "o pon USAR_GPU = False y vuelve a ejecutar.")
import psutil
_libre = psutil.virtual_memory().available / 1e9
if _libre < 5:                                   # el kernel necesita ~5 GB (PyTorch + CUDA + datos)
    print(f"⚠ Solo hay {_libre:.1f} GB de RAM libre. El entrenamiento usa ~5 GB: cierra pestañas de Chrome "
          "o ventanas de VS Code que no uses, o puede fallar con MemoryError.")
from pathlib import Path
from types import SimpleNamespace

RAIZ = Path.cwd().parent if Path.cwd().name == "notebooks" else Path.cwd()
sys.path.insert(0, str(RAIZ))
logging.getLogger("absl").setLevel(logging.ERROR)
warnings.filterwarnings("ignore", category=UserWarning)

import numpy as np, pandas as pd, torch, keras
import plotly.io as pio
pio.renderers.default = "plotly_mimetype"   # VS Code y JupyterLab lo dibujan nativo
from IPython.display import display, Markdown
from gemelo import (config, datos_emg, datos_poses, datos_externos, metricas, contrastivo, vivo, formas,
                    estudiante, refuerzo, episodios)
import ia_mano as ia, simulador as sm

from gemelo.tablero_vivo import TableroVivo

if REENTRENAR_TODO:
    REENTRENAR_BASE = REENTRENAR_CONTRASTIVO = REENTRENAR_CABEZAS = REENTRENAR_FORMAS = True
    REENTRENAR_ESTUDIANTE = REENTRENAR_REFUERZO = True
config.crear_carpetas()
config.fijar_semillas(SEMILLA)
(config.MODELOS / "esp32").mkdir(exist_ok=True)
RESUMEN = []          # tabla final: todo modelo con su R²

# Tablero en vivo: la secuencia completa del entrenamiento en el navegador
SECCIONES = ["0 · Configuración", "1 · D1 EMG sintético", "2 · D2 poses sintéticas", "3 · D3 webcam",
             "4 · D4 EMG real (UCI)", "5 · Línea base 8-32-16-7", "6 · Contrastivo en vivo",
             "7 · Formas descubiertas", "8 · Cabezas multitarea", "9 · Red de formas de la mano",
             "10 · Estudiante ESP32", "11 · Refuerzo de servos", "12 · Exportación y R²"]
TAB = TableroVivo(config.REPORTES / "vivo", SECCIONES)
TAB.iniciar(abrir=ABRIR_TABLERO)
vivo.TABLERO = TAB
TAB.seccion(0)

def informar(*partes):
    texto = " ".join(map(str, partes))
    print(texto)
    for linea in texto.splitlines():
        TAB.log(linea)

def necesita(ruta, forzar):
    return forzar or not Path(ruta).exists()

def anotar(modelo, tarea, r2, tipo_r2, datos, **extra):
    RESUMEN.append({"modelo": modelo, "tarea": tarea, "R²": round(float(r2), 4), "tipo de R²": tipo_r2,
                    "datos": datos, **{k: round(float(v), 4) for k, v in extra.items()}})
    TAB.r2(RESUMEN[-1])

gpu = torch.cuda.get_device_name(0) if torch.cuda.is_available() else "NO HAY GPU (se usará la CPU)"
print(f"Keras {keras.__version__} sobre {keras.backend.backend()} · PyTorch {torch.__version__} · GPU: {gpu}")
print(f"Código: {RAIZ}\nDatos:  {config.DATOS}\nModelos: {config.MODELOS}")
display(Markdown(f"**Tablero en vivo:** [{TAB.url}]({TAB.url}) — se actualiza solo mientras corre el notebook."))

Keras 3.15.1 sobre torch · PyTorch 2.14.1+cu126 · GPU: NVIDIA GeForce RTX 4050 Laptop GPU
Código: C:\Users\rolda\OneDrive\Escritorio\GEMELO DIGITAL
Datos:  C:\Users\rolda\gemelo_mano\datos
Modelos: C:\Users\rolda\OneDrive\Escritorio\GEMELO DIGITAL\modelos


**Tablero en vivo:** [http://127.0.0.1:8765/index.html](http://127.0.0.1:8765/index.html) — se actualiza solo mientras corre el notebook.

## 1. D1 — EMG sintético con dos vistas físicas

Cada repetición se simula **dos veces con las mismas fuentes musculares** y distinto sensor (otra colocación de electrodos, otra piel, otro ruido, otro 60 Hz, otro artefacto). Ese par es el *positivo físico* del contrastivo.

160 personas virtuales repartidas en los 5 niveles de dificultad del currículo (±15 % por persona), 25 % de contracciones suaves para el control proporcional. División **por persona**: 70 % entrenamiento, 15 % validación, 15 % prueba (personas nunca vistas).

In [3]:
TAB.seccion(1)
RUTA_D1 = config.DATOS / "D1_emg_sintetico.h5"
if necesita(RUTA_D1, REGENERAR_D1):
    from tqdm.auto import tqdm
    barra = tqdm(total=N_PERSONAS_D1, desc="personas virtuales")
    t0 = time.time()
    datos_emg.generar_d1(n_personas=N_PERSONAS_D1, rondas=3, semilla=SEMILLA, ruta=RUTA_D1,
                         progreso=lambda k, n: (barra.update(1), TAB.progreso(k, n, "personas virtuales")))
    barra.close()
    informar(f"D1 generado en {time.time() - t0:.0f} s")
d1, MAN_D1 = datos_emg.cargar_h5(RUTA_D1)
TR, VA, TE = (np.flatnonzero(d1["split"] == s) for s in range(3))
PRIOR = np.bincount(d1["gesto"][TR], minlength=ia.NUM_GESTOS) / len(TR)
SEQ = episodios.secuencia_prueba(d1, semilla=SEMILLA)    # persona nunca vista: los intentos del visor 3D
RNG_EP = np.random.default_rng(SEMILLA)
informar(f"D1: {MAN_D1['n']:,} ventanas · {MAN_D1['n_personas']} personas · hash {MAN_D1['hash']}")
informar(f"    entrenamiento {len(TR):,} · validación {len(VA):,} · prueba {len(TE):,}")
tabla = pd.crosstab(pd.Series([ia.NOMBRES[g] for g in ia.GESTOS])[d1["gesto"]].values,
                    pd.Series(["entrenamiento", "validación", "prueba"])[d1["split"]].values)
vivo.tabla(tabla)

D1: 80,640 ventanas · 160 personas · hash 5ed4a4a8ad708c2f
    entrenamiento 56,448 · validación 12,096 · prueba 12,096


col_0,entrenamiento,prueba,validación
row_0,,,
Abierta,8064,1728,1728
Extensión muñeca,8064,1728,1728
Flexión muñeca,8064,1728,1728
Pinza,8064,1728,1728
Puño,8064,1728,1728
Reposo,8064,1728,1728
Señalar,8064,1728,1728


col_0,entrenamiento,prueba,validación
row_0,,,
Abierta,8064,1728,1728
Extensión muñeca,8064,1728,1728
Flexión muñeca,8064,1728,1728
Pinza,8064,1728,1728
Puño,8064,1728,1728
Reposo,8064,1728,1728
Señalar,8064,1728,1728


In [4]:
# La misma contracción (puño) vista por dos sensores distintos
from plotly.subplots import make_subplots
import plotly.graph_objects as go
i = TR[np.flatnonzero((d1["gesto"][TR] == ia.GESTOS.index("puno")) & (d1["ventana_idx"][TR] == 10))[0]]
fig = make_subplots(rows=2, cols=1, shared_xaxes=True, subplot_titles=["Canal 1 · flexores", "Canal 2 · extensores"])
for c in range(2):
    for vista, color, guion in (("x_a", vivo.COLORES[0], "solid"), ("x_b", vivo.COLORES[1], "dot")):
        fig.add_trace(go.Scatter(y=d1[vista][i, :, c], name=f"vista {vista[-1].upper()}", showlegend=c == 0,
                                 line=dict(color=color, width=1.5, dash=guion)), row=c + 1, col=1)
fig.update_layout(title="Positivo físico: misma contracción de puño, dos colocaciones de electrodos", height=420,
                  paper_bgcolor=vivo.FONDO, plot_bgcolor=vivo.FONDO, yaxis_title="ADC", yaxis2_title="ADC",
                  xaxis2_title="ms", margin=dict(t=60, b=40))
vivo.mostrar(fig)

## 2. D2 — Poses de mano sintéticas (21 puntos)

600 manos virtuales (tamaño, largo de falanges, separación de dedos, temblor, orientación de la cámara). 75 % gestos con amplitud parcial y 25 % transiciones entre dos gestos. Mismo formato que la webcam (D3).

In [5]:
TAB.seccion(2)
RUTA_D2 = config.DATOS / "D2_poses_sinteticas.h5"
if necesita(RUTA_D2, REGENERAR_D2):
    datos_poses.generar_d2(n=N_POSES_D2, semilla=SEMILLA + 1, ruta=RUTA_D2)
d2, MAN_D2 = datos_emg.cargar_h5(RUTA_D2)
TR2, VA2, TE2 = (np.flatnonzero(d2["split"] == s) for s in range(3))
informar(f"D2: {MAN_D2['n']:,} poses · {MAN_D2['n_manos']} manos · {d2['mezcla'].mean() * 100:.0f} % transiciones · "
      f"hash {MAN_D2['hash']}")
vivo.mostrar(vivo.figura_manos(datos_emg.POSES_6, list(range(ia.NUM_GESTOS)), "Las 7 poses objetivo del gemelo"))
rng = np.random.default_rng(SEMILLA)
muestra = [rng.choice(np.flatnonzero((d2["gesto"] == g) & ~d2["mezcla"])) for g in range(ia.NUM_GESTOS)]
vivo.mostrar(vivo.figura_manos(d2["dof"][muestra], list(range(ia.NUM_GESTOS)),
                  "Ejemplos de D2 (amplitud parcial y ruido; gris = objetivo)"))

D2: 60,000 poses · 600 manos · 25 % transiciones · hash ad0f468f1b703fb4


## 3. D3 — Poses reales con la webcam (MediaPipe)

Se llena con `capturar_poses.py` (ver instrucciones abajo). Cuando exista, la sección 9 lo usa para comparar las poses reales con el espacio de formas aprendido.

In [6]:
TAB.seccion(3)
RUTA_D3 = config.DATOS / "D3_poses_webcam.h5"
d3 = None
if RUTA_D3.exists():
    d3, _ = datos_emg.cargar_h5(RUTA_D3)
    informar(f"D3: {len(d3['gesto']):,} poses reales en {len(np.unique(d3['sesion']))} sesiones")
    vivo.tabla(pd.Series([ia.NOMBRES[ia.GESTOS[g]] for g in d3["gesto"]]).value_counts().rename("poses"))
else:
    py_venv = Path(sys.executable)
    display(Markdown(f"**Aún no hay D3.** Para capturarlo, en una terminal:\n\n"
                     f"```\n\"{py_venv}\" \"{RAIZ / 'capturar_poses.py'}\"\n```\n"
                     "Teclas 0-6 eligen el gesto, ESPACIO graba/pausa, q guarda y sale."))

**Aún no hay D3.** Para capturarlo, en una terminal:

```
"C:\Users\rolda\gemelo_mano\venv\Scripts\python.exe" "C:\Users\rolda\OneDrive\Escritorio\GEMELO DIGITAL\capturar_poses.py"
```
Teclas 0-6 eligen el gesto, ESPACIO graba/pausa, q guarda y sale.

## 4. D4 — EMG real público: UCI *EMG data for gestures*

36 personas, pulsera MYO de 8 canales (Lobov et al., *Sensors* 2018, CC BY 4.0). Por persona se eligen el canal más flexor y el más extensor para parecerse a la prótesis, y se escala con la ganancia del circuito real. Gestos comunes con la mano: reposo, puño, flexión, extensión y mano abierta; lo demás queda sin etiqueta (−1) y sirve para el aprendizaje no supervisado.

In [7]:
TAB.seccion(4)
RUTA_D4 = config.DATOS / "D4_emg_uci.h5"
if necesita(RUTA_D4, REGENERAR_D4):
    datos_externos.generar_d4_uci(semilla=SEMILLA + 2, ruta=RUTA_D4)
d4, MAN_D4 = datos_emg.cargar_h5(RUTA_D4)
informar(f"D4: {MAN_D4['n']:,} ventanas reales · {len(np.unique(d4['persona']))} personas · paso {MAN_D4['paso_ms']} ms")
vivo.tabla(pd.Series(["sin etiqueta" if g < 0 else ia.NOMBRES[ia.GESTOS[g]] for g in d4["gesto"]])
        .value_counts().rename("ventanas"))

D4: 71,013 ventanas reales · 36 personas · paso 50 ms


sin etiqueta        55671
Extensión muñeca     3837
Reposo               3825
Flexión muñeca       3808
Puño                 3665
Abierta               207
Name: ventanas, dtype: int64

sin etiqueta        55671
Extensión muñeca     3837
Reposo               3825
Flexión muñeca       3808
Puño                 3665
Abierta               207
Name: ventanas, dtype: int64

## 5. Línea base: la red actual 8-32-16-7

La misma red que hoy corre en el ESP32, entrenada con D1 (8 características por ventana). Es el número a superar.

In [8]:
TAB.seccion(5)
F = d1["caracteristicas"]
RUTA_BASE = config.CACHE / "red_actual_d1.h5"

def intento_base(modelo, epoca):
    p = keras.ops.convert_to_numpy(modelo(F[SEQ["idx"]].astype(np.float32), training=False))
    TAB.episodio(episodios.episodio_firmware(SEQ, p, f"Red actual 8-32-16-7 · época {epoca} (así la mueve el ESP32)", 5))

if necesita(RUTA_BASE, REENTRENAR_BASE):
    base, _ = estudiante.entrenar_red_actual(F[TR], d1["gesto"][TR], F[VA], d1["gesto"][VA],
                                             callbacks=[estudiante.CadaEpoca(intento_base, 5)])
    ia.guardar_red(base, RUTA_BASE, {"origen": "D1 (línea base)"})
else:
    base = ia.cargar_red(RUTA_BASE)
intento_base(base, "final")
p_base = keras.ops.convert_to_numpy(base(F[TE].astype(np.float32), training=False))
est_te = ~d1["transicion"][TE]
r_base = metricas.clasificacion(d1["gesto"][TE], p_base, PRIOR)
r_base_e = metricas.clasificacion(d1["gesto"][TE][est_te], p_base[est_te], PRIOR)
informar(f"Red actual en personas nuevas: precisión {r_base['precision'] * 100:.1f} % · "
      f"estables {r_base_e['precision'] * 100:.1f} % · pseudo-R² {r_base['pseudo_r2']:.3f} · F1 {r_base['f1_macro']:.3f}")
anotar("Red actual 8-32-16-7", "gesto", r_base["pseudo_r2"], "pseudo-R² McFadden", "D1 prueba",
       precision=r_base["precision"])
vivo.mostrar(vivo.figura_confusion(r_base["confusion"], "Red actual — matriz de confusión (personas nuevas, %)"))

Red actual en personas nuevas: precisión 85.8 % · estables 85.9 % · pseudo-R² 0.817 · F1 0.858


## 6. Aprendizaje contrastivo — en vivo

**Fase 1 · SimCLR (no supervisado):** el único positivo de cada ventana es su otra vista. La red **nunca ve el gesto**; los colores del panel son solo para que tú juzgues si los separó por su cuenta.
**Fase 2 · SupCon (supervisado):** además, todas las ventanas del mismo gesto son positivas entre sí.

Qué mirar mientras entrena:
- **Nube 3D:** al inicio todo mezclado; reposo y flexión se separan primero; puño, pinza y señalar son los que tardan (y los que hoy hacen ruido).
- **Manos:** para cada grupo que descubre el agrupamiento (sin etiquetas), la pose que la red le asocia, contra la objetivo en gris.
- **Sondas:** kNN y pseudo-R² del gesto, **R² de la pose**, y kNN en **datos reales UCI** (¿lo del gemelo sirve en brazos reales?).
- **Completitud:** NMI, ARI y pureza: qué tanto los grupos coinciden con los gestos.

In [9]:
TAB.seccion(6)
RUTA_COD = config.MODELOS / "codificador_contrastivo.h5"
RUTA_REG = config.CACHE / "contrastivo_registro.pkl"
ENTRENADO_AHORA = necesita(RUTA_COD, REENTRENAR_CONTRASTIVO) or not RUTA_REG.exists()
if ENTRENADO_AHORA:
    ent = contrastivo.EntrenadorContrastivo(d1, d4 if USAR_UCI_EN_CONTRASTIVO else None, lote=LOTE, semilla=SEMILLA)
    panel = vivo.PanelContrastivo() if VER_EN_VIVO else None

    def al_terminar(e, r):
        uci = f" · kNN UCI {r['knn_real_uci'] * 100:4.1f} %" if "knn_real_uci" in r else ""
        linea = (f"época {r['epoca']:2d} [{r['fase']}] pérdida {r['perdida']:.3f} · kNN {r['knn'] * 100:4.1f} % · "
                 f"R² pose {r['r2_pose']:.3f} · pseudo-R² {r['pseudo_r2']:.3f} · NMI {r['nmi']:.3f}{uci} · "
                 f"{r['segundos']:.1f} s")
        informar(linea)
        TAB.log(linea)
        TAB.progreso(r["epoca"], EPOCAS_SIMCLR + EPOCAS_SUPCON, r["fase"])
        dof = e.ridge.predict(contrastivo.embeddings(e.cod, d1["x_a"][SEQ["idx"]], normalizar=True))
        TAB.episodio(episodios.episodio_pose(SEQ, dof, f"Contrastivo · época {r['epoca']} · {r['fase']}", 6))
        if panel:
            panel.actualizar(e)

    ent.entrenar([("SimCLR (no supervisado)", EPOCAS_SIMCLR, False),
                  ("SupCon (supervisado)", EPOCAS_SUPCON, True)], al_terminar)
    COD = ent.cod
    COD.save(RUTA_COD)
    COD.save(RUTA_COD.with_suffix(".keras"))
    with open(RUTA_REG, "wb") as f:
        pickle.dump(ent.registro(), f)
else:
    COD = keras.models.load_model(RUTA_COD, compile=False)
    informar("Codificador cargado de", RUTA_COD)
with open(RUTA_REG, "rb") as f:
    REG = pickle.load(f)
if not ENTRENADO_AHORA:                  # sin reentrenar: el panel de la última época guardada
    vivo.PanelContrastivo().actualizar(SimpleNamespace(**REG, d1=d1))

época  0 [inicio] pérdida nan · kNN 63.5 % · R² pose 0.437 · pseudo-R² 0.583 · NMI 0.603 · kNN UCI 30.6 % · 0.0 s


época  1 [SimCLR (no supervisado)] pérdida 5.603 · kNN 72.2 % · R² pose 0.517 · pseudo-R² 0.682 · NMI 0.586 · kNN UCI 30.2 % · 8.5 s


época  2 [SimCLR (no supervisado)] pérdida 3.897 · kNN 74.2 % · R² pose 0.511 · pseudo-R² 0.719 · NMI 0.642 · kNN UCI 32.9 % · 8.3 s


época  3 [SimCLR (no supervisado)] pérdida 2.598 · kNN 76.2 % · R² pose 0.524 · pseudo-R² 0.741 · NMI 0.704 · kNN UCI 33.7 % · 8.2 s


época  4 [SimCLR (no supervisado)] pérdida 2.123 · kNN 76.9 % · R² pose 0.524 · pseudo-R² 0.750 · NMI 0.682 · kNN UCI 32.6 % · 8.3 s


...

época 26 [SupCon (supervisado)] pérdida 5.190 · kNN 82.3 % · R² pose 0.568 · pseudo-R² 0.799 · NMI 0.777 · kNN UCI 42.8 % · 8.7 s


época 27 [SupCon (supervisado)] pérdida 5.199 · kNN 82.2 % · R² pose 0.568 · pseudo-R² 0.799 · NMI 0.789 · kNN UCI 42.9 % · 8.6 s


época 28 [SupCon (supervisado)] pérdida 5.194 · kNN 82.6 % · R² pose 0.568 · pseudo-R² 0.799 · NMI 0.792 · kNN UCI 41.4 % · 8.4 s


época 29 [SupCon (supervisado)] pérdida 5.193 · kNN 82.4 % · R² pose 0.568 · pseudo-R² 0.799 · NMI 0.779 · kNN UCI 43.0 % · 7.8 s


época 30 [SupCon (supervisado)] pérdida 5.176 · kNN 82.5 % · R² pose 0.568 · pseudo-R² 0.799 · NMI 0.782 · kNN UCI 42.5 % · 7.7 s


In [10]:
# Repetición: recorre el aprendizaje época por época (también queda en reportes/)
anim = vivo.animacion(REG["instantaneas"], d1["gesto"][REG["i_mon"]])
anim.write_html(config.REPORTES / "entrenamiento_contrastivo.html", include_plotlyjs="cdn")
vivo.mostrar(anim)

# ¿Cuánto logró SOLO la fase no supervisada?
h = pd.DataFrame(REG["historial"])
fin_fase = h.groupby("fase", sort=False).tail(1).set_index("fase")
vivo.tabla(fin_fase[["epoca", "knn", "sonda_logistica", "pseudo_r2", "r2_pose", "nmi", "ari", "pureza"]
                 + (["knn_real_uci"] if "knn_real_uci" in h else [])].round(3))
u = h.iloc[-1]
anotar("Codificador contrastivo (sonda lineal)", "pose 6 GDL", u["r2_pose"], "R² (Ridge sobre embedding)", "D1 validación")
anotar("Codificador contrastivo (sonda logística)", "gesto", u["pseudo_r2"], "pseudo-R² McFadden", "D1 validación",
       precision=u["sonda_logistica"])

,epoca,knn,sonda_logistica,pseudo_r2,r2_pose,nmi,ari,pureza,knn_real_uci
fase,,,,,,,,,
inicio,0,0.635,0.652,0.583,0.437,0.603,0.411,0.550,0.306
SimCLR (no supervisado),15,0.762,0.802,0.758,0.472,0.701,0.569,0.698,0.264
SupCon (supervisado),30,0.825,0.838,0.799,0.568,0.782,0.706,0.824,0.425


## 7. Espacio latente: las formas que descubrió (no supervisado)

Agrupamiento con mezclas gaussianas sobre el embedding de personas **nunca vistas**, sin usar etiquetas. Se barre el número de grupos con el BIC: si salen más de 7, la red encontró *subformas* (por ejemplo, puño suave y puño fuerte); si dos gestos caen en el mismo grupo, el sensor de 2 canales no los distingue.

In [11]:
TAB.seccion(7)
RUTA_EMB = config.CACHE / "embeddings.npz"
if necesita(RUTA_EMB, REENTRENAR_CONTRASTIVO) or os.path.getmtime(RUTA_EMB) < os.path.getmtime(RUTA_COD):
    E1 = contrastivo.embeddings(COD, d1["x_a"], normalizar=True)
    E4 = contrastivo.embeddings(COD, d4["x_a"], normalizar=True)
    np.savez_compressed(RUTA_EMB, E1=E1, E4=E4)
E = np.load(RUTA_EMB)
E1, E4 = E["E1"], E["E4"]

from sklearn.mixture import GaussianMixture
from sklearn.linear_model import Ridge
from sklearn.decomposition import PCA
sel = np.random.default_rng(SEMILLA).choice(TE[~d1["transicion"][TE]], 4000, replace=False)
ks = list(range(4, 15))
bic = [GaussianMixture(k, covariance_type="diag", random_state=0, n_init=2).fit(E1[sel]).bic(E1[sel]) for k in ks]
K_MEJOR = ks[int(np.argmin(bic))]
fig = go.Figure(go.Scatter(x=ks, y=bic, mode="lines+markers", line=dict(color=vivo.COLORES[0], width=2),
                           hovertemplate="k=%{x}: BIC %{y:.0f}<extra></extra>"))
fig.add_vline(x=K_MEJOR, line=dict(color=vivo.GRIS, dash="dash"))
fig.update_layout(title=f"¿Cuántas formas hay? BIC por número de grupos (mínimo en k = {K_MEJOR})", height=320,
                  xaxis_title="grupos", yaxis_title="BIC (menor = mejor)", paper_bgcolor=vivo.FONDO,
                  plot_bgcolor=vivo.FONDO)
vivo.mostrar(fig)

y_sel = d1["gesto"][sel].astype(int)
res = {k: metricas.grupos(E1[sel], y_sel, k=k) for k in sorted({ia.NUM_GESTOS, K_MEJOR})}
vivo.tabla(pd.DataFrame({f"k = {k}": {m: r[m] for m in ("nmi", "ari", "pureza", "silueta")} for k, r in res.items()}).round(3))
g = res[K_MEJOR]
comp = pd.crosstab(pd.Series(g["asignacion"], name="grupo") + 1,
                   pd.Series([ia.NOMBRES[ia.GESTOS[x]] for x in y_sel], name="gesto real"), normalize="index") * 100
display(Markdown("**Composición de cada grupo descubierto (% de sus ventanas):**"))
vivo.tabla(comp.round(0))

ridge = Ridge(1.0).fit(E1[TR], d1["pose"][TR])
manos = np.clip(ridge.predict(g["gmm"].means_), [0, 0, 0, 0, 0, -1], 1)
orden = np.argsort(g["gesto_de_grupo"], kind="stable")
vivo.mostrar(vivo.figura_manos(manos[orden], [g["gesto_de_grupo"][i] for i in orden],
                  f"Pose de cada uno de los {K_MEJOR} grupos descubiertos (gris = objetivo del gesto mayoritario)",
                  etiquetas=[f"g{i + 1}: " + (vivo.NOMBRES[g['gesto_de_grupo'][i]] if g['gesto_de_grupo'][i] >= 0 else "vacío")
                             for i in orden]))
anotar(f"Agrupamiento GMM (k = {K_MEJOR})", "formas sin etiqueta", g["nmi"], "NMI (análogo de R² para grupos)",
       "D1 prueba", pureza=g["pureza"], ari=g["ari"])

,k = 7,k = 14
nmi,0.777,0.687
ari,0.658,0.482
pureza,0.796,0.818
silueta,0.302,0.180


**Composición de cada grupo descubierto (% de sus ventanas):**

gesto real,Abierta,Extensión muñeca,Flexión muñeca,Pinza,Puño,Reposo,Señalar
grupo,,,,,,,
1,0.0,0.0,0.0,26.0,9.0,0.0,65.0
2,0.0,100.0,0.0,0.0,0.0,0.0,0.0
3,0.0,0.0,100.0,0.0,0.0,0.0,0.0
4,0.0,0.0,0.0,0.0,0.0,100.0,0.0
5,98.0,2.0,0.0,0.0,0.0,0.0,0.0
6,0.0,100.0,0.0,0.0,0.0,0.0,0.0
7,0.0,0.0,100.0,0.0,0.0,0.0,0.0
8,0.0,0.0,0.0,24.0,65.0,0.0,11.0
9,99.0,1.0,0.0,0.0,0.0,0.0,0.0


In [12]:
# El gemelo y los brazos reales en el mismo espacio
pca = PCA(3, random_state=0).fit(E1[sel])
vivo.mostrar(vivo.figura_nube(pca.transform(E1[sel]), y_sel, "Espacio contrastivo — personas virtuales nunca vistas (D1 prueba)"))
m4 = (d4["split"] == 2) & (d4["gesto"] >= 0)
sel4 = np.random.default_rng(1).choice(np.flatnonzero(m4), min(3000, m4.sum()), replace=False)
vivo.mostrar(vivo.figura_nube(pca.transform(E4[sel4]), d4["gesto"][sel4].astype(int),
                 "El mismo espacio con EMG REAL (UCI, personas de prueba)"))
from sklearn.neighbors import KNeighborsClassifier
knn = KNeighborsClassifier(10, metric="cosine").fit(E1[TR], d1["gesto"][TR])
p4 = knn.predict_proba(E4[sel4])
r4 = metricas.clasificacion(d4["gesto"][sel4].astype(int), p4, PRIOR)
informar(f"Transferencia gemelo → real (kNN entrenado solo con D1): precisión {r4['precision'] * 100:.1f} % "
      f"en 5 gestos (azar = 20 %), pseudo-R² {r4['pseudo_r2']:.3f}")
anotar("kNN sobre embedding (solo gemelo)", "gesto en EMG real", r4["pseudo_r2"], "pseudo-R² McFadden",
       "D4 UCI prueba", precision=r4["precision"])

Transferencia gemelo → real (kNN entrenado solo con D1): precisión 36.1 % en 5 gestos (azar = 20 %), pseudo-R² -7.238


## 8. Cabezas multitarea: gesto + pose (6 GDL) + fuerza

Entrada: el embedding contrastivo de las **3 últimas ventanas** (300 ms de contexto) + sus 8 características. Tres salidas: el gesto, la posición continua de los 5 dedos y la muñeca (control proporcional) y la fuerza de la contracción. Se ve en vivo por época.

In [13]:
TAB.seccion(8)
XC = contrastivo.entradas_cabezas(E1, F, d1["ventana_idx"])
sub = lambda idx: {k: v[idx] for k, v in XC.items()}
obj = lambda idx: {"gesto": d1["gesto"][idx], "pose": d1["pose"][idx], "fuerza": d1["fuerza"][idx]}
RUTA_CAB = config.MODELOS / "cabezas_multitarea.h5"

class CallbackCabezas(keras.callbacks.Callback):
    def __init__(self, panel):
        super().__init__()
        self.panel, self.h = panel, []
    def on_epoch_end(self, epoca, logs=None):
        r, _ = contrastivo.evaluar_cabezas(self.model, XC, d1, VA, PRIOR)
        self.h.append({"precision": r["gesto_todas"]["precision"], "pseudo_r2": r["gesto_todas"]["pseudo_r2"],
                       "r2_pose": r["pose"]["r2"], "r2_fuerza": r["fuerza"]["r2"]})
        s = self.model.predict(sub(SEQ["idx"]), verbose=0)
        TAB.episodio(episodios.episodio_pose(SEQ, s["pose"], f"Cabezas multitarea · época {epoca + 1} (pose continua)", 8))
        if self.panel:
            self.panel.actualizar(self.h, [("precision", "precisión gesto"), ("pseudo_r2", "pseudo-R² gesto"),
                                           ("r2_pose", "R² pose"), ("r2_fuerza", "R² fuerza")])

if necesita(RUTA_CAB, REENTRENAR_CABEZAS or REENTRENAR_CONTRASTIVO):
    config.fijar_semillas(SEMILLA)
    CAB = contrastivo.crear_cabezas(carac_adaptar=XC["carac_ctx"][TR])
    cb = CallbackCabezas(vivo.PanelCurvas("Cabezas multitarea (validación)", total=80) if VER_EN_VIVO else None)
    CAB.fit(sub(TR), obj(TR), validation_data=(sub(VA), obj(VA)), epochs=80, batch_size=512, verbose=0,
            callbacks=[cb, keras.callbacks.EarlyStopping(patience=8, restore_best_weights=True)])
    CAB.save(RUTA_CAB)
    CAB.save(RUTA_CAB.with_suffix(".keras"))
else:
    CAB = keras.models.load_model(RUTA_CAB, compile=False)
R_CAB, SAL_TE = contrastivo.evaluar_cabezas(CAB, XC, d1, TE, PRIOR)
gt, ge = R_CAB["gesto_todas"], R_CAB["gesto_estables"]
vivo.tabla(pd.DataFrame({
    "Red actual 8-32-16-7": [r_base["precision"], r_base_e["precision"], r_base["pseudo_r2"], r_base["f1_macro"], None, None],
    "Contrastivo + cabezas": [gt["precision"], ge["precision"], gt["pseudo_r2"], gt["f1_macro"], R_CAB["pose"]["r2"],
                              R_CAB["fuerza"]["r2"]]},
    index=["precisión (todas)", "precisión (estables)", "pseudo-R² gesto", "F1 macro", "R² pose", "R² fuerza"]).round(4))
vivo.mostrar(vivo.figura_confusion(gt["confusion"], "Contrastivo + cabezas — matriz de confusión (personas nuevas, %)"))
vivo.mostrar(vivo.figura_barras(R_CAB["pose"]["r2_por_salida"], "R² de la pose por grado de libertad (personas nuevas)"))
vivo.mostrar(vivo.figura_barras({ia.NOMBRES[g]: v for g, v in gt["recall"].items()}, "Acierto por gesto (personas nuevas)",
                   eje="recall"))
anotar("Contrastivo + cabezas", "gesto", gt["pseudo_r2"], "pseudo-R² McFadden", "D1 prueba", precision=gt["precision"])
anotar("Contrastivo + cabezas", "pose 6 GDL", R_CAB["pose"]["r2"], "R²", "D1 prueba")
anotar("Contrastivo + cabezas", "fuerza", R_CAB["fuerza"]["r2"], "R²", "D1 prueba")

,Red actual 8-32-16-7,Contrastivo + cabezas
precisión (todas),0.8581,0.8945
precisión (estables),0.8590,0.8969
pseudo-R² gesto,0.8173,0.8552
F1 macro,0.8583,0.8948
R² pose,NaN,0.8043
R² fuerza,NaN,0.8760


## 9. Red de formas de la mano (D2, y D3 si existe)

Autoencoder de los 21 puntos con un espacio latente de **3 dimensiones** (se ve tal cual) y una cabeza que recupera los 6 grados de libertad. Cada gesto ocupa una región; las transiciones son caminos entre regiones.

In [14]:
TAB.seccion(9)
RUTA_FORMAS = config.MODELOS / "red_formas.h5"
L2 = d2["landmarks"]
SEL_F = np.concatenate([np.flatnonzero((d2["split"] == 2) & (d2["gesto"] == g) & ~d2["mezcla"])[:2]
                        for g in range(ia.NUM_GESTOS)])

def intento_formas(modelo, epoca):
    s = modelo.predict(L2[SEL_F], verbose=0)
    TAB.episodio(episodios.episodio_formas(d2["dof"][SEL_F], s["dof"], d2["gesto"][SEL_F],
                                           f"Red de formas · época {epoca} (de 21 puntos a la mano)", 9))

if necesita(RUTA_FORMAS, REENTRENAR_FORMAS):
    config.fijar_semillas(SEMILLA)
    RF = formas.crear_red_formas()
    cbf = formas.CallbackFormas(vivo.PanelCurvas("Red de formas (validación)", total=60) if VER_EN_VIVO else None,
                                L2[VA2], d2["dof"][VA2], d2["gesto"][VA2].astype(int))
    RF.fit(L2[TR2], {"reconstruccion": L2[TR2], "dof": d2["dof"][TR2]},
           validation_data=(L2[VA2], {"reconstruccion": L2[VA2], "dof": d2["dof"][VA2]}), epochs=60, batch_size=512,
           verbose=0, callbacks=[cbf, estudiante.CadaEpoca(intento_formas, 2),
                                 keras.callbacks.EarlyStopping(patience=8, restore_best_weights=True)])
    RF.save(RUTA_FORMAS)
    RF.save(RUTA_FORMAS.with_suffix(".keras"))
    formas.codificador_de(RF).save(config.MODELOS / "codificador_formas.keras")
else:
    RF = keras.models.load_model(RUTA_FORMAS, compile=False)
R_F = formas.evaluar(RF, L2[TE2], d2["dof"][TE2])
informar(f"Manos nunca vistas: R² reconstrucción {R_F['reconstruccion']:.4f} · R² 6 GDL {R_F['dof']['r2']:.4f}")
vivo.mostrar(vivo.figura_barras(R_F["dof"]["r2_por_salida"], "Red de formas — R² por grado de libertad (manos nuevas)"))
Z = formas.codificador_de(RF).predict(L2[TE2], verbose=0)
fig = vivo.figura_nube(Z, d2["gesto"][TE2].astype(int), "Espacio de formas de la mano (latente 3D, manos nuevas)")
fig.write_html(config.REPORTES / "espacio_formas.html", include_plotlyjs="cdn")
vivo.mostrar(fig)
anotar("Red de formas", "reconstrucción 21 puntos", R_F["reconstruccion"], "R²", "D2 prueba")
anotar("Red de formas", "pose 6 GDL desde 21 puntos", R_F["dof"]["r2"], "R²", "D2 prueba")
if d3 is not None:
    s3 = RF.predict(d3["landmarks"], verbose=0)
    r3 = metricas.r2(d3["landmarks"].reshape(len(d3["landmarks"]), -1), s3["reconstruccion"].reshape(len(d3["landmarks"]), -1))
    informar(f"D3 webcam: R² de reconstrucción de poses reales {r3['r2']:.4f}")
    vivo.mostrar(vivo.figura_nube(formas.codificador_de(RF).predict(d3["landmarks"], verbose=0), d3["gesto"].astype(int),
                     "Tus poses reales (webcam) en el espacio de formas"))
    anotar("Red de formas", "reconstrucción poses reales", r3["r2"], "R²", "D3 webcam")

Manos nunca vistas: R² reconstrucción 0.8878 · R² 6 GDL 0.9872


## 10. Estudiante para el ESP32 (destilación)

El profesor (CNN + cabezas) no cabe en el firmware actual. El estudiante sí: `Normalization` + `Dense` sobre las **mismas 8 características** que calcula `protesis_tiempo_real.ino`, entrenado con las probabilidades del profesor (conocimiento oscuro). Se exporta con el exportador de siempre y se verifica que la copia en C prediga exactamente lo mismo.

In [15]:
TAB.seccion(10)
RUTA_EST = config.MODELOS / "estudiante_red.h5"
if necesita(RUTA_EST, REENTRENAR_ESTUDIANTE or REENTRENAR_CABEZAS or REENTRENAR_CONTRASTIVO):
    config.fijar_semillas(SEMILLA)
    probs_tr = CAB.predict(sub(TR), batch_size=4096, verbose=0)["gesto"]
    def intento_est(modelo, epoca):
        p = keras.ops.convert_to_numpy(modelo(F[SEQ["idx"]].astype(np.float32), training=False))
        TAB.episodio(episodios.episodio_firmware(SEQ, p, f"Estudiante ESP32 · época {epoca}", 10))
    EST, _ = estudiante.entrenar_estudiante(F[TR], d1["gesto"][TR], probs_tr, F[VA], d1["gesto"][VA],
                                            callbacks=[estudiante.CadaEpoca(intento_est, 5)])
    ia.compilar(EST)
    ia.guardar_red(EST, RUTA_EST, {"origen": "destilado del profesor contrastivo (D1)", "ventanas": int(len(TR))})
else:
    EST = ia.cargar_red(RUTA_EST)
p_est = keras.ops.convert_to_numpy(EST(F[TE].astype(np.float32), training=False))
r_est = metricas.clasificacion(d1["gesto"][TE], p_est, PRIOR)
r_est_e = metricas.clasificacion(d1["gesto"][TE][est_te], p_est[est_te], PRIOR)
dif, acuerdo = estudiante.verificar_equivalencia_esp32(EST, F[TE])
vivo.tabla(pd.DataFrame({"Red actual 8-32-16-7": [r_base["precision"], r_base_e["precision"], r_base["pseudo_r2"],
                                               ia.contar_parametros(base)],
                      "Estudiante 8-64-32-16-7": [r_est["precision"], r_est_e["precision"], r_est["pseudo_r2"],
                                                  ia.contar_parametros(EST)]},
                     index=["precisión (todas)", "precisión (estables)", "pseudo-R² gesto", "parámetros"]).round(4))
informar(f"Copia en C vs Keras: diferencia máxima {dif:.2e}, mismas predicciones en {acuerdo * 100:.1f} %")
GANADOR = EST if r_est["pseudo_r2"] >= r_base["pseudo_r2"] else base
ia.exportar_red_c(GANADOR, config.MODELOS / "esp32" / "modelo_red.h")
informar("modelos/esp32/modelo_red.h <-", "estudiante" if GANADOR is EST else "red actual (el estudiante no la superó)")
anotar("Estudiante ESP32 (destilado)", "gesto", r_est["pseudo_r2"], "pseudo-R² McFadden", "D1 prueba",
       precision=r_est["precision"])

,Red actual 8-32-16-7,Estudiante 8-64-32-16-7
precisión (todas),0.8581,0.8576
precisión (estables),0.8590,0.8600
pseudo-R² gesto,0.8173,0.8167
parámetros,935.0000,3303.0000


Copia en C vs Keras: diferencia máxima 7.55e-07, mismas predicciones en 100.0 %
modelos/esp32/modelo_red.h <- red actual (el estudiante no la superó)


## 11. Refuerzo de los servos

Un agente aprende qué comando dar a cada servo para que la mano física virtual (tendones con holgura, acople de la muñeca) logre cada pose. R² entre la pose lograda y la objetivo.

In [16]:
TAB.seccion(11)
RUTA_POL = config.MODELOS / "politica_servos.h5"
mano = sm.ManoFisica()
AG = refuerzo.AgenteServos(mano, semilla=SEMILLA)
if necesita(RUTA_POL, REENTRENAR_REFUERZO):
    panel = vivo.PanelCurvas("Refuerzo de los servos") if VER_EN_VIVO else None
    for i in range(ITERACIONES_REFUERZO):
        r = AG.iteracion_completa()
        if i % 20 == 0 or i == ITERACIONES_REFUERZO - 1:
            TAB.progreso(i + 1, ITERACIONES_REFUERZO, "iteraciones")
            TAB.episodio(episodios.episodio_refuerzo(AG, f"Refuerzo · iteración {i + 1} (con exploración)", 11, RNG_EP))
        if panel and (i % 40 == 0 or i == ITERACIONES_REFUERZO - 1):
            panel.actualizar(AG.historial, [("r2_pose", "R² pose lograda"), ("error_medio", "error medio de pose")])
    AG.guardar(RUTA_POL)
else:
    pol = keras.models.load_model(RUTA_POL, compile=False)
    AG.politica.set_weights(pol.get_weights())
R_RL = AG.r2_por_gdl()
informar(f"R² pose lograda vs objetivo: {AG.evaluar()['r2_pose']:.4f} · error medio {AG.evaluar()['error_medio']:.4f}")
vivo.mostrar(vivo.figura_barras(R_RL["r2_por_salida"], "Refuerzo — R² por grado de libertad"))
vivo.mostrar(vivo.figura_manos(AG.logradas(), list(range(ia.NUM_GESTOS)), "Pose que logra la mano física con los comandos aprendidos (gris = objetivo)"))
ia.exportar_poses_c(AG.poses(), config.MODELOS / "esp32" / "poses_aprendidas.h")
p_seq = keras.ops.convert_to_numpy(EST(F[SEQ["idx"]].astype(np.float32), training=False))
TAB.episodio(episodios.episodio_firmware(SEQ, p_seq, "Sistema completo: EMG → estudiante ESP32 → comandos aprendidos → mano",
                                         11, poses=AG.poses()))
anotar("Agente de servos (REINFORCE)", "pose lograda", AG.evaluar()["r2_pose"], "R²", "mano física virtual")

R² pose lograda vs objetivo: 0.9967 · error medio 0.0170


## 12. Exportación y resumen de R²

In [17]:
TAB.seccion(12)
TABLA = pd.DataFrame(RESUMEN)
TABLA.to_csv(config.REPORTES / "resumen_r2.csv", index=False, encoding="utf-8")
display(Markdown("### Resumen: todo modelo con su R²"))
vivo.tabla(TABLA)

ficha = {"proyecto": "Prótesis mioeléctrica — gemelo digital", "autor": config.AUTOR,
         "entorno": {"keras": keras.__version__, "backend": keras.backend.backend(), "torch": torch.__version__,
                     "gpu": gpu},
         "datasets": {"D1": MAN_D1, "D2": MAN_D2, "D4": {k: v for k, v in MAN_D4.items()
                                                       if k != "canales_elegidos_por_persona"},
                      "D3": None if d3 is None else {"n": int(len(d3["gesto"]))}},
         "resumen_r2": RESUMEN,
         "contrastivo": {"fases": {"SimCLR": EPOCAS_SIMCLR, "SupCon": EPOCAS_SUPCON}, "lote": LOTE,
                         "ultima_epoca": REG["historial"][-1], "grupos_bic": K_MEJOR},
         "cabezas": {"gesto": {k: v for k, v in R_CAB["gesto_todas"].items() if k != "confusion"},
                     "pose": R_CAB["pose"], "fuerza": R_CAB["fuerza"]},
         "esp32": {"modelo_red.h": "estudiante" if GANADOR is EST else "red actual",
                   "equivalencia_c": {"dif_max": dif, "acuerdo": acuerdo}},
         "semilla": SEMILLA}
config.guardar_json(ficha, config.MODELOS / "ficha_modelo.json")
informar("Archivos exportados:")
for p in sorted(config.MODELOS.rglob("*")):
    if p.is_file():
        informar(f"  {p.relative_to(config.RAIZ_PROYECTO)}  ({p.stat().st_size / 1024:,.0f} KB)")
informar("\nPara el ESP32: copia modelos/esp32/modelo_red.h y poses_aprendidas.h junto a protesis_tiempo_real.ino")
estatico = TAB.terminar()
display(Markdown(f"**Tablero completo guardado:** `{estatico.relative_to(config.RAIZ_PROYECTO)}` "
                 "(se abre con doble clic, sin servidor)."))

### Resumen: todo modelo con su R²

,modelo,tarea,R²,tipo de R²,datos,precision,pureza,ari
0,Red actual 8-32-16-7,gesto,0.8173,pseudo-R² McFadden,D1 prueba,0.8581,NaN,NaN
1,Codificador contrastivo (sonda lineal),pose 6 GDL,0.5681,R² (Ridge sobre embedding),D1 validación,NaN,NaN,NaN
2,Codificador contrastivo (sonda logística),gesto,0.7989,pseudo-R² McFadden,D1 validación,0.8375,NaN,NaN
3,Agrupamiento GMM (k = 14),formas sin etiqueta,0.6874,NMI (análogo de R² para grupos),D1 prueba,NaN,0.8177,0.4817
4,kNN sobre embedding (solo gemelo),gesto en EMG real,-7.2382,pseudo-R² McFadden,D4 UCI prueba,0.3615,NaN,NaN
5,Contrastivo + cabezas,gesto,0.8552,pseudo-R² McFadden,D1 prueba,0.8945,NaN,NaN
6,Contrastivo + cabezas,pose 6 GDL,0.8043,R²,D1 prueba,NaN,NaN,NaN
7,Contrastivo + cabezas,fuerza,0.8760,R²,D1 prueba,NaN,NaN,NaN
8,Red de formas,reconstrucción 21 puntos,0.8878,R²,D2 prueba,NaN,NaN,NaN
9,Red de formas,pose 6 GDL desde 21 puntos,0.9872,R²,D2 prueba,NaN,NaN,NaN


Archivos exportados:
  modelos\cabezas_multitarea.h5  (536 KB)
  modelos\cabezas_multitarea.keras  (532 KB)
  modelos\codificador_contrastivo.h5  (445 KB)
  modelos\codificador_contrastivo.keras  (455 KB)
  modelos\codificador_formas.keras  (88 KB)
  modelos\esp32\modelo_red.h  (18 KB)
  modelos\esp32\poses_aprendidas.h  (1 KB)
  modelos\estudiante_red.h5  (49 KB)
  modelos\ficha_modelo.json  (7 KB)
  modelos\politica_servos.h5  (22 KB)
  modelos\red_formas.h5  (487 KB)
  modelos\red_formas.keras  (482 KB)

Para el ESP32: copia modelos/esp32/modelo_red.h y poses_aprendidas.h junto a protesis_tiempo_real.ino


**Tablero completo guardado:** `reportes\tablero.html` (se abre con doble clic, sin servidor).